In [ ]:
!pip install musdb
!pip install norbert museval soundfile
!pip install mir_eval

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 963.2/963.2 kB 14.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 102.8/102.8 kB 3.8 MB/s eta 0:00:00


In [ ]:
import librosa
import numpy as np
import musdb
from google.colab import drive
import random
import IPython.display as ipd
from scipy.interpolate import interp1d
import os
import torch
import torch.nn as nn
from torch.utils.data import Dataset, DataLoader
import glob
import torch.nn.functional as F
import museval
from tqdm import tqdm
import norbert
import mir_eval
import pickle

# **LOADING MUSDB18 FROM GOOGLE DRIVE**

In [ ]:
# Mount Google Drive
drive.mount('/content/drive')

# Initialize the database using your specific path
# Note: download=False because we are using local files on Drive
#db = musdb.DB(root="/content/drive/MyDrive/MUSDB18/musdb18", subsets="train", download=False)

# Verify tracks detected
#print(f"Dataset loaded successfully! Number of tracks found in train subset: {len(db.tracks)}")

Mounted at /content/drive


# **PREPROCESSING PHASE**

In [ ]:
if 'db' in locals() and len(db.tracks) > 0:

    # --- OUTPUT PATH CONFIGURATION ---
    output_folder = "/content/drive/MyDrive/MUSDB18/MUSDB18_Preprocessed_Full"
    os.makedirs(output_folder, exist_ok=True)
    if os.path.exists(output_folder):
      print(f"SUCCESS: Output folder is ready: {output_folder}")
    else:
      print("ERROR: Unable to create output folder. Check Drive permissions.")

    # --- PARAMETERS CONFIGURATION (From Paper) ---
    TARGET_SR = 10880
    DURATION_SECONDS = 6
    SAMPLES_PER_BLOCK = TARGET_SR * DURATION_SECONDS # 65280
    N_FFT = 1022
    HOP_LENGTH = 256
    WINDOW = 'hann'
    NETWORK_DIM = 256
    TARGETS = ['vocals', 'drums', 'bass', 'other']

    # Log-frequency axis preparation
    linear_freqs = np.linspace(0, 1, 512)
    log_freqs = np.geomspace(1, 10, NETWORK_DIM)
    log_freqs = (log_freqs - log_freqs.min()) / (log_freqs.max() - log_freqs.min())

    print(f"Starting global pipeline on {len(db.tracks)} tracks...")
    print(f"Log and Lin files will be saved in: {output_folder}\n")

    # --- MAIN LOOP ---
    for idx, track in enumerate(db.tracks):
        try:
            original_sr = track.rate

            # STEP 1: Mono conversion (Average of stereo channels)
            mix_mono = np.mean(track.audio.T, axis=0)

            # STEP 2: Downsampling to 10,880 Hz
            mix_resampled = librosa.resample(mix_mono, orig_sr=original_sr, target_sr=TARGET_SR)

            # Repeat Steps 1 & 2 for the 4 target stems
            targets_resampled = {}
            for t in TARGETS:
                t_mono = np.mean(track.targets[t].audio.T, axis=0)
                targets_resampled[t] = librosa.resample(t_mono, orig_sr=original_sr, target_sr=TARGET_SR)

            # STEP 3: Temporal Segmentation
            signal_length = len(mix_resampled)
            num_full_blocks = signal_length // SAMPLES_PER_BLOCK

            mix_blocks = []
            target_blocks = {t: [] for t in TARGETS}

            # Extract standard segments
            for i in range(num_full_blocks):
                start = i * SAMPLES_PER_BLOCK
                end = start + SAMPLES_PER_BLOCK
                mix_blocks.append(mix_resampled[start:end])
                for t in TARGETS:
                    target_blocks[t].append(targets_resampled[t][start:end])

            # Handle final block (padding logic implied by slicing)
            if signal_length % SAMPLES_PER_BLOCK != 0:
                mix_blocks.append(mix_resampled[-SAMPLES_PER_BLOCK:])
                for t in TARGETS:
                    target_blocks[t].append(targets_resampled[t][-SAMPLES_PER_BLOCK:])

            # Initialize lists for Log and Lin data
            track_mix_log = []
            track_mix_lin = []
            track_targets_lin = {t: [] for t in TARGETS}

            # STEP 4, 5 & 6: STFT and Log-Scaling
            for b_idx in range(len(mix_blocks)):
                # --- Process MIX Spectrogram ---
                # Linear version (512x256)
                mag_mix_linear = np.abs(librosa.stft(mix_blocks[b_idx], n_fft=N_FFT, hop_length=HOP_LENGTH, window=WINDOW))
                track_mix_lin.append(mag_mix_linear)

                # Logarithmic version (256x256) for network input
                log_mix_block = np.zeros((NETWORK_DIM, NETWORK_DIM), dtype=np.float32)
                for f_idx in range(NETWORK_DIM):
                    interp_mix = interp1d(linear_freqs, mag_mix_linear[:, f_idx], kind='linear', bounds_error=False, fill_value=0)
                    log_mix_block[:, f_idx] = interp_mix(log_freqs)
                track_mix_log.append(log_mix_block)

                # --- Process STEM Spectrograms ---
                for t in TARGETS:
                    mag_target_linear = np.abs(librosa.stft(target_blocks[t][b_idx], n_fft=N_FFT, hop_length=HOP_LENGTH, window=WINDOW))
                    track_targets_lin[t].append(mag_target_linear)

            # Convert to NumPy arrays
            track_mix_log = np.array(track_mix_log, dtype=np.float32)
            track_mix_lin = np.array(track_mix_lin, dtype=np.float32)

            safe_track_name = "".join([c if c.isalnum() else "_" for c in track.name])

            # --- SAVE TO DRIVE ---
            np.save(f"{output_folder}/{idx:03d}_{safe_track_name}_X_mix_log.npy", track_mix_log)
            np.save(f"{output_folder}/{idx:03d}_{safe_track_name}_X_mix_lin.npy", track_mix_lin)

            for t in TARGETS:
                target_lin_np = np.array(track_targets_lin[t], dtype=np.float32)
                np.save(f"{output_folder}/{idx:03d}_{safe_track_name}_Y_{t}_lin.npy", target_lin_np)

            print(f"-> [{idx+1}/{len(db.tracks)}] Processed and saved: {track.name} ({len(track_mix_log)} blocks)")

            # --- RAM CLEANUP ---
            del track_mix_log, track_mix_lin, track_targets_lin
            del mix_mono, mix_resampled, targets_resampled, mix_blocks, target_blocks

        except Exception as e:
            print(f"!!! Error processing track {track.name}: {e}")

    print("\n[COMPLETED] Preprocessing finished!")
else:
    print("ERROR: Initialize dataset before running pipeline.")

SUCCESS: Output folder is ready: /content/drive/MyDrive/MUSDB18/MUSDB18_Preprocessed_Full
Starting global pipeline on 100 tracks...
Log and Lin files will be saved in: /content/drive/MyDrive/MUSDB18/MUSDB18_Preprocessed_Full

-> [1/100] Processed and saved: A Classic Education - NightOwl (29 blocks)
-> [2/100] Processed and saved: ANiMAL - Clinic A (40 blocks)
-> [3/100] Processed and saved: ANiMAL - Easy Tiger (35 blocks)
-> [4/100] Processed and saved: ANiMAL - Rockshow (28 blocks)
-> [5/100] Processed and saved: Actions - Devil's Words (33 blocks)
-> [6/100] Processed and saved: Actions - One Minute Smile (28 blocks)
-> [7/100] Processed and saved: Actions - South Of The Water (30 blocks)
-> [8/100] Processed and saved: Aimee Norwich - Child (32 blocks)
-> [9/100] Processed and saved: Alexander Ross - Goodbye Bolero (70 blocks)
-> [10/100] Processed and saved: Alexander Ross - Velvet Curtain (86 blocks)
-> [11/100] Processed and saved: Angela Thomas Wade - Milk Cow Blues (36 blocks)

# **Dataset Custom PyTorch**

In [ ]:
class MUSDB18Dataset(Dataset):
    def __init__(self, folder_path, augment=False, mask_prob=0.5):
        self.folder_path = folder_path
        self.targets = ['vocals', 'drums', 'bass', 'other']
        self.augment = augment
        self.mask_prob = mask_prob

        # Find files based on log prefix
        self.mix_files = sorted(glob.glob(os.path.join(folder_path, "*_X_mix_log.npy")))
        if not self.mix_files:
            raise FileNotFoundError(f"No files found in {folder_path}.")

        self.samples = []
        for mix_file in self.mix_files:
            base_prefix = mix_file.replace("_X_mix_log.npy", "")
            # Used mmap to read shape without loading full data
            num_blocks = np.load(mix_file, mmap_mode='r').shape[0]

            for i in range(num_blocks):
                self.samples.append({'prefix': base_prefix, 'block_idx': i, 'pitch_shift': False})
                if self.augment:
                    self.samples.append({'prefix': base_prefix, 'block_idx': i, 'pitch_shift': True})

        # Recomputing log scale after augmentation
        self.linear_freqs = np.linspace(0, 1, 512)
        fl = np.geomspace(1, 10, 256)
        self.log_freqs = (fl - fl.min()) / (fl.max() - fl.min())

        # Precomputing vectorized interpolation indices
        pos = self.log_freqs * (512 - 1)
        self._lo = np.floor(pos).astype(np.int64)
        self._hi = np.minimum(self._lo + 1, 512 - 1)
        self._w = (pos - self._lo).astype(np.float32)

    def __len__(self):
        return len(self.samples)

    def _pitch_shift_freq(self, linear_mag):
        n = linear_mag.shape[0]
        shift = int(round(n * (2 ** (1/12) - 1)))
        out = np.zeros_like(linear_mag)
        out[shift:, :] = linear_mag[:n - shift, :]
        return out

    def _log_from_lin(self, linear_mag):
        lower = linear_mag[self._lo, :]
        upper = linear_mag[self._hi, :]
        log_block = lower + (upper - lower) * self._w[:, None]
        return log_block.astype(np.float32)

    def __getitem__(self, idx):
        info = self.samples[idx]
        block_idx = info['block_idx']

        x_lin_data = np.array(np.load(f"{info['prefix']}_X_mix_lin.npy", mmap_mode='r')[block_idx])
        y_lin_data = {t: np.array(np.load(f"{info['prefix']}_Y_{t}_lin.npy", mmap_mode='r')[block_idx])
                      for t in self.targets}

        recompute_log = False

        if info['pitch_shift']:
            x_lin_data = self._pitch_shift_freq(x_lin_data)
            y_lin_data = {t: self._pitch_shift_freq(y_lin_data[t]) for t in self.targets}
            recompute_log = True

        # Time Masking
        if self.augment and random.random() < self.mask_prob:
            info_other = self.samples[random.randint(0, len(self.samples) - 1)]
            other = np.array(np.load(f"{info_other['prefix']}_X_mix_lin.npy", mmap_mode='r')[info_other['block_idx']])
            Fdim, Tdim = x_lin_data.shape
            fw, tw = random.randint(1, 60), random.randint(1, 40)
            f0, t0 = random.randint(0, Fdim - fw), random.randint(0, Tdim - tw)
            fs, ts = slice(f0, f0 + fw), slice(t0, t0 + tw)
            x_lin_data[fs, ts] = 0.5 * (x_lin_data[fs, ts] + other[fs, ts])
            for t in self.targets:
                y_lin_data[t][fs, ts] = 0.5 * (y_lin_data[t][fs, ts] + other[fs, ts])
            recompute_log = True

        if recompute_log:
            x_log_data = self._log_from_lin(x_lin_data)
        else:
            x_log_data = np.array(np.load(f"{info['prefix']}_X_mix_log.npy", mmap_mode='r')[block_idx])

        return torch.tensor(x_log_data).unsqueeze(0), torch.tensor(x_lin_data).unsqueeze(0), {t: torch.tensor(y_lin_data[t]).unsqueeze(0) for t in self.targets}

# **MODEL ARCHITECTURE**

In [ ]:
class ConvBlock(nn.Module):
    def __init__(self, in_ch, out_ch):
        super().__init__()
        self.conv = nn.Sequential(
            nn.Conv2d(in_ch, out_ch, kernel_size=3, padding=1),
            nn.BatchNorm2d(out_ch),
            nn.ReLU(inplace=True),
            nn.Conv2d(out_ch, out_ch, kernel_size=3, padding=1),
            nn.BatchNorm2d(out_ch),
            nn.ReLU(inplace=True)
        )
    def forward(self, x):
        return self.conv(x)

class DecoderBlock(nn.Module):
    def __init__(self, in_ch, out_ch, use_dropout=False):
        super().__init__()
        self.up = nn.ConvTranspose2d(in_ch, out_ch, kernel_size=2, stride=2)
        self.conv = ConvBlock(out_ch * 2, out_ch)
        self.dropout = nn.Dropout2d(p=0.5) if use_dropout else nn.Identity()

    def forward(self, x, skip):
        x = self.up(x)
        x = torch.cat([x, skip], dim=1)
        x = self.dropout(x)
        return self.conv(x)

class MultiOutputUNet(nn.Module):
    def __init__(self):
        super().__init__()
        # ENCODER (Depth 6)
        self.enc1 = ConvBlock(1, 32)
        self.enc2 = ConvBlock(32, 64)
        self.enc3 = ConvBlock(64, 128)
        self.enc4 = ConvBlock(128, 256)
        self.enc5 = ConvBlock(256, 512)
        self.enc6 = ConvBlock(512, 1024)
        self.pool = nn.MaxPool2d(kernel_size=2, stride=2)

        # BOTTLENECK
        self.bottleneck = ConvBlock(1024, 2048)

        # DECODER (Symmetric, with Dropout on deeper levels)
        self.dec6 = DecoderBlock(2048, 1024, use_dropout=True)
        self.dec5 = DecoderBlock(1024, 512, use_dropout=True)
        self.dec4 = DecoderBlock(512, 256, use_dropout=True)
        self.dec3 = DecoderBlock(256, 128, use_dropout=False)
        self.dec2 = DecoderBlock(128, 64, use_dropout=False)
        self.dec1 = DecoderBlock(64, 32, use_dropout=False)

        # 4-channel convolutional output (one for each instrument)
        self.final_conv = nn.Conv2d(32, 4, kernel_size=1)

    def forward(self, x):
        s1 = self.enc1(x)
        s2 = self.enc2(self.pool(s1))
        s3 = self.enc3(self.pool(s2))
        s4 = self.enc4(self.pool(s3))
        s5 = self.enc5(self.pool(s4))
        s6 = self.enc6(self.pool(s5))

        b = self.bottleneck(self.pool(s6))

        d6 = self.dec6(b, s6)
        d5 = self.dec5(d6, s5)
        d4 = self.dec4(d5, s4)
        d3 = self.dec3(d4, s3)
        d2 = self.dec2(d3, s2)
        d1 = self.dec1(d2, s1)

        masks = torch.sigmoid(self.final_conv(d1))
        return masks

# **EBW Loss Function (Energy-Based Weighting)**

In [ ]:
class EBWLoss(nn.Module):
    """Custom Loss based on Energy-Based Weighting (EBW)"""
    def __init__(self):
        super().__init__()
        self.l1_loss = nn.L1Loss(reduction='sum')
        self.targets_keys = ['vocals', 'drums', 'bass', 'other']

    def forward(self, pred_masks, mix_linear, targets_dict):
        """
        Args:
            pred_masks: Network output (Batch, 4, 256, 256) -> Logarithmic Scale
            mix_linear: Original mix from dataset (Batch, 1, 512, 256) -> Linear Scale
            targets_dict: Dictionary of ground truth targets -> All (Batch, 1, 512, 256) Linear Scale
        """
        losses = {}
        energies = {}

        # Target shape to restore the mask to the original linear scale (512, 256)
        target_height, target_width = mix_linear.shape[2], mix_linear.shape[3]

        # Calculate Indirect L1 Loss and Energy for each stem
        for idx, t in enumerate(self.targets_keys):
            mask_i_log = pred_masks[:, idx:idx+1, :, :] # Logarithmic channel (256, 256)

            # Resize the mask to the original linear scale before applying loss
            mask_i_linear = F.interpolate(mask_i_log, size=(target_height, target_width), mode='bilinear', align_corners=False)

            # Apply the mask on the Linear Mix (Original Shape)
            pred_spec_i = mask_i_linear * mix_linear

            true_spec_i = targets_dict[t] # Already in linear scale (512, 256)

            # Calculate L1 error (Summation)
            losses[t] = self.l1_loss(pred_spec_i, true_spec_i)

            # Calculate average energy (mean of the magnitude of the ground truth)
            energies[t] = torch.mean(torch.abs(true_spec_i)) + 1e-8

        # Calculate dynamic EBW InstP2 weights (Square of energy ratios)
        max_energy = max(energies.values())

        total_loss = 0.0
        for t in self.targets_keys:
            # Using the InstP2 variant where weights are based on energy imbalance
            w_i = (max_energy / energies[t]) ** 2
            total_loss += w_i * losses[t]

        return total_loss

# **TRAINING LOOP**

Copying preprocessed data to local storage for faster training access.

In [ ]:
!rm -rf /content/local_preprocessed
!cp -r /content/drive/MyDrive/MUSDB18/MUSDB18_Preprocessed_Full /content/local_preprocessed

In [ ]:
# Device Config
device = torch.device('cuda' if torch.cuda.is_available() else 'cpu')
print(f"Device in use: {device}")

# Modules Initialization
model = MultiOutputUNet().to(device)
criterion = EBWLoss()
optimizer = torch.optim.Adam(model.parameters(), lr=0.001, weight_decay=0.01)

PATH_CHECKPOINT = "/content/drive/MyDrive/MUSDB18/MultiOutputUNet_epoch_augment_400.pth"
START_EPOCH = 0


if os.path.exists(PATH_CHECKPOINT):
    print("[INFO] Resuming from checkpoint...")

    checkpoint = torch.load(PATH_CHECKPOINT, map_location=device)
    model.load_state_dict(checkpoint)
    START_EPOCH = 400

print(f"Training resumes from epoch: {START_EPOCH + 1}\n")

# Dataloader setup
folder_dataset = "/content/local_preprocessed"
dataset_train = MUSDB18Dataset(folder_dataset, augment=True)

dataloader_train = DataLoader(
    dataset_train,
    batch_size=64,
    shuffle=True,
    num_workers=2,
    pin_memory=True,
    persistent_workers=True
)

NUM_EPOCHS = 1000

print(f"\nTraining started on {len(dataset_train)} blocks...")
model.train()

for epoch in range(START_EPOCH, NUM_EPOCHS):
    running_loss = 0.0
    for batch_idx, (mix_log, mix_lin, targets_lin) in enumerate(tqdm(dataloader_train, desc=f"Epoch {epoch+1}/{NUM_EPOCHS}")):
        # Tensors moved on GPU
        mix_log = mix_log.to(device)
        mix_lin = mix_lin.to(device)
        for t in targets_lin:
            targets_lin[t] = targets_lin[t].to(device)

        optimizer.zero_grad()
        pred_masks_log = model(mix_log)
        loss = criterion(pred_masks_log, mix_lin, targets_lin)
        loss.backward()
        optimizer.step()
        running_loss += loss.item()

    epoch_loss = running_loss / len(dataloader_train)
    print(f"Epoch [{epoch+1}/{NUM_EPOCHS}] -> Average Loss per Batch: {epoch_loss:.4f}")

    # Saving the weights every X epochs for backup
    if (epoch + 1) % 50 == 0:
        torch.save(model.state_dict(), f"/content/drive/MyDrive/MUSDB18/MultiOutputUNet_epoch_augment_{epoch+1}.pth")

# Final weights
torch.save(model.state_dict(), "/content/drive/MyDrive/MUSDB18/MultiOutputUNet_weights_final_augment.pth")
print("\n[FINISH] Model trained and weights saved")

## **Testing and Reconstruction Pipeline (End-to-End). Scroll the OutPut for the numerical results.**

In [ ]:
#CONFIGURATIONS
TARGET_SR = 10880
DURATION_SECONDS = 6
SAMPLES_PER_BLOCK = TARGET_SR * DURATION_SECONDS
N_FFT = 1022
HOP_LENGTH = 256
WINDOW = 'hann'
NETWORK_DIM = 256
TARGETS = ['vocals', 'drums', 'bass', 'other']

device = torch.device('cuda' if torch.cuda.is_available() else 'cpu')

linear_freqs = np.linspace(0, 1, 512)
log_freqs = np.geomspace(1, 10, NETWORK_DIM)
log_freqs = (log_freqs - log_freqs.min()) / (log_freqs.max() - log_freqs.min())

#INFERENCE AND RECONSTRUCTION FUNCTION
def separate_track(track, model):
    original_sr = track.rate
    mix_mono = np.mean(track.audio.T, axis=0)
    mix_resampled = librosa.resample(mix_mono, orig_sr=original_sr, target_sr=TARGET_SR)

    signal_length = len(mix_resampled)
    num_full_blocks = signal_length // SAMPLES_PER_BLOCK

    reconstructed_audio = {t: np.zeros(signal_length, dtype=np.float32) for t in TARGETS}
    blocks_to_process = []
    block_indices = []

    for i in range(num_full_blocks):
        start = i * SAMPLES_PER_BLOCK
        end = start + SAMPLES_PER_BLOCK
        blocks_to_process.append(mix_resampled[start:end])
        block_indices.append((start, end))

    if signal_length % SAMPLES_PER_BLOCK != 0:
        blocks_to_process.append(mix_resampled[-SAMPLES_PER_BLOCK:])
        block_indices.append((signal_length - SAMPLES_PER_BLOCK, signal_length))

    model.eval()
    with torch.no_grad():
        for block, (start, end) in zip(blocks_to_process, block_indices):
            stft_mix = librosa.stft(block, n_fft=N_FFT, hop_length=HOP_LENGTH, window=WINDOW)
            mag_mix = np.abs(stft_mix)

            log_mix_block = np.zeros((NETWORK_DIM, NETWORK_DIM), dtype=np.float32)
            for f_idx in range(NETWORK_DIM):
                interp_mix = interp1d(linear_freqs, mag_mix[:, f_idx], kind='linear', bounds_error=False, fill_value=0)
                log_mix_block[:, f_idx] = interp_mix(log_freqs)

            log_tensor = torch.tensor(log_mix_block, dtype=torch.float32).unsqueeze(0).unsqueeze(0).to(device)
            pred_masks_log = model(log_tensor)

            pred_masks_lin = F.interpolate(pred_masks_log, size=(512, 256), mode='bilinear', align_corners=False)
            pred_masks_lin = pred_masks_lin.squeeze(0).cpu().numpy()

            est_mags = pred_masks_lin * mag_mix
            v = est_mags ** 2
            v = np.transpose(v, (2, 1, 0))
            v = np.expand_dims(v, axis=2)

            x_stft_norbert = np.transpose(stft_mix, (1, 0))
            x_stft_norbert = np.expand_dims(x_stft_norbert, axis=2)

            # Wiener filtering using Norbert
            est_stft = norbert.wiener(v, x_stft_norbert, iterations=1)

            for i, t in enumerate(TARGETS):
                stem_stft = est_stft[:, :, 0, i].T
                block_audio = librosa.istft(stem_stft, n_fft=N_FFT, hop_length=HOP_LENGTH, window=WINDOW)
                reconstructed_audio[t][start:end] = block_audio

    return reconstructed_audio

# EVALUATION FUNCTION
def evaluate_track(track, reconstructed_audio):
    """Calculates frame-by-frame SDR, SIR, SAR using mir_eval (BSS Eval v3) for MONO tracks"""
    t_mono_vocals = np.mean(track.targets['vocals'].audio.T, axis=0)
    ref_resampled_vocals = librosa.resample(t_mono_vocals, orig_sr=track.rate, target_sr=TARGET_SR)
    min_len = min(len(ref_resampled_vocals), len(reconstructed_audio['vocals']))

    ref_matrix = np.zeros((4, min_len), dtype=np.float32)
    est_matrix = np.zeros((4, min_len), dtype=np.float32)

    for i, t in enumerate(TARGETS):
        t_mono = np.mean(track.targets[t].audio.T, axis=0)
        ref_resampled = librosa.resample(t_mono, orig_sr=track.rate, target_sr=TARGET_SR)
        ref_matrix[i, :] = ref_resampled[:min_len]
        est_matrix[i, :] = reconstructed_audio[t][:min_len]

    window_size = TARGET_SR  # 1 second window
    num_frames = min_len // window_size

    track_sdr = [[] for _ in range(4)]
    track_sir = [[] for _ in range(4)]
    track_sar = [[] for _ in range(4)]

    for f in range(num_frames):
        start = f * window_size
        end = start + window_size

        ref_frame = ref_matrix[:, start:end]
        est_frame = est_matrix[:, start:end]

        if np.sum(np.abs(ref_frame)) < 1e-5:
            continue

        try:
            sdr_f, sir_f, sar_f, _ = mir_eval.separation.bss_eval_sources(
                ref_frame, est_frame, compute_permutation=False
            )
            for i in range(4):
                track_sdr[i].append(sdr_f[i])
                track_sir[i].append(sir_f[i])
                track_sar[i].append(sar_f[i])
        except Exception:
            continue

    return track_sdr, track_sir, track_sar

In [ ]:
print("Loading TEST dataset...")
db_test = musdb.DB(root="/content/drive/MyDrive/MUSDB18/musdb18", subsets="test", download=False)
print(f"Tracks found: {len(db_test.tracks)}")

print("Loading pre-trained model...")
model_test = MultiOutputUNet().to(device)
model_test.load_state_dict(torch.load("/content/drive/MyDrive/MUSDB18/MultiOutputUNet_weights_final_augment.pth", map_location=torch.device('cpu'), weights_only=True))
#model_test.load_state_dict(torch.load("/content/drive/MyDrive/MUSDB18/MultiOutputUNet_weights_final_augment.pth", weights_only=True))

# Definizione del percorso del file di salvataggio progressi su Drive
CHECKPOINT_EVAL_PATH = "/content/drive/MyDrive/MUSDB18/eval_checkpoint.pkl"

# Logica di ripristino da crash o interruzione
if os.path.exists(CHECKPOINT_EVAL_PATH):
    print("[INFO] Trovato un checkpoint esistente. Recupero i progressi salvati...")
    with open(CHECKPOINT_EVAL_PATH, "rb") as f:
        checkpoint_data = pickle.load(f)
    total_frames = checkpoint_data["total_frames"]
    processed_tracks = checkpoint_data["processed_tracks"]
    print(f"[INFO] Ripresa dell'esecuzione. {len(processed_tracks)} tracce già analizzate estratte con successo.")
else:
    print("[INFO] Nessun checkpoint trovato. Avvio la valutazione da zero.")
    # Accumulate frames for Global Median calculation
    total_frames = {t: {"SDR": [], "SIR": [], "SAR": []} for t in TARGETS}
    processed_tracks = set()

print("\n--- STARTING EVALUATION --")
for idx, track in enumerate(db_test.tracks):
    # Salta a costo zero le canzoni già fatte nelle run precedenti
    if track.name in processed_tracks:
        print(f"[{idx+1}/{len(db_test.tracks)}] Skipping (Già Elaborata): {track.name}")
        continue

    print(f"[{idx+1}/{len(db_test.tracks)}] Processing: {track.name}")

    audio_reconstructed = separate_track(track, model_test)
    sdr, sir, sar = evaluate_track(track, audio_reconstructed)

    for i, t in enumerate(TARGETS):
        total_frames[t]["SDR"].extend(sdr[i])
        total_frames[t]["SIR"].extend(sir[i])
        total_frames[t]["SAR"].extend(sar[i])

    # Aggiunge la traccia all'elenco dei completati e scrive subito il file di backup su Drive
    processed_tracks.add(track.name)
    checkpoint_data = {
        "total_frames": total_frames,
        "processed_tracks": processed_tracks
    }
    with open(CHECKPOINT_EVAL_PATH, "wb") as f:
        pickle.dump(checkpoint_data, f)

    print(f"   -> Vocals SDR: {np.nanmedian(sdr[0]):.2f} dB [Progress Backup Saved]")


# --- 5. FINAL RESULTS (GLOBAL MEDIAN) ---
print("\n" + "="*40)
print(" GLOBAL STANDARD RESULTS")
print("="*40)
for t in TARGETS:
    print(f"\nInstrument: {t.upper()}")
    print(f"{'Metrics':<10} | {'Mdn (Mediana)':<15} | {'M (Mean)':<12} | {'SD (Std Dev.)':<12}")
    print("-" * 60)

    for metric in ["SDR", "SIR", "SAR"]:
        # Convertiamo in array numpy per usare le funzioni statistiche che ignorano i NaN (silenzio)
        valori = np.array(total_frames[t][metric])

        mdn_val = np.nanmedian(valori)
        m_val = np.nanmean(valori)
        sd_val = np.nanstd(valori)

        print(f"{metric:<10} | {mdn_val:>11.2f} dB | {m_val:>10.2f} dB | {sd_val:>10.2f} dB")
    print("-" * 60)

Loading TEST dataset...
Tracks found: 50
Loading pre-trained model...
[INFO] Trovato un checkpoint esistente. Recupero i progressi salvati...
[INFO] Ripresa dell'esecuzione. 47 tracce già analizzate estratte con successo.

--- STARTING EVALUATION --
[1/50] Skipping (Già Elaborata): AM Contra - Heart Peripheral
[2/50] Skipping (Già Elaborata): Al James - Schoolboy Facination
[3/50] Skipping (Già Elaborata): Angels In Amplifiers - I'm Alright
[4/50] Skipping (Già Elaborata): Arise - Run Run Run
[5/50] Skipping (Già Elaborata): BKS - Bulldozer
[6/50] Skipping (Già Elaborata): BKS - Too Much
[7/50] Skipping (Già Elaborata): Ben Carrigan - We'll Talk About It All Tonight
[8/50] Skipping (Già Elaborata): Bobby Nobody - Stitch Up
[9/50] Skipping (Già Elaborata): Buitraker - Revo X
[10/50] Skipping (Già Elaborata): Carlos Gonzalez - A Place For Us
[11/50] Skipping (Già Elaborata): Cristina Vane - So Easy
[12/50] Skipping (Già Elaborata): Detsky Sad - Walkie Talkie
[13/50] Skipping (Già Elabora

/tmp/ipykernel_578/1445477139.py:109: FutureWarning: mir_eval.separation.bss_eval_sources
	Deprecated as of mir_eval version 0.8.
	It will be removed in mir_eval version 0.9.
  sdr_f, sir_f, sar_f, _ = mir_eval.separation.bss_eval_sources(


   -> Vocals SDR: 7.70 dB [Progress Backup Saved]
[49/50] Processing: We Fell From The Sky - Not You


/tmp/ipykernel_578/1445477139.py:109: FutureWarning: mir_eval.separation.bss_eval_sources
	Deprecated as of mir_eval version 0.8.
	It will be removed in mir_eval version 0.9.
  sdr_f, sir_f, sar_f, _ = mir_eval.separation.bss_eval_sources(


   -> Vocals SDR: 2.68 dB [Progress Backup Saved]
[50/50] Processing: Zeno - Signs


/tmp/ipykernel_578/1445477139.py:109: FutureWarning: mir_eval.separation.bss_eval_sources
	Deprecated as of mir_eval version 0.8.
	It will be removed in mir_eval version 0.9.
  sdr_f, sir_f, sar_f, _ = mir_eval.separation.bss_eval_sources(


   -> Vocals SDR: 6.12 dB [Progress Backup Saved]

 GLOBAL STANDARD RESULTS

Instrument: VOCALS
Metrics    | Mdn (Mediana)   | M (Mean)     | SD (Std Dev.)
------------------------------------------------------------
SDR        |        5.51 dB |       1.73 dB |      13.06 dB
SIR        |        8.83 dB |       6.29 dB |      11.73 dB
SAR        |        9.44 dB |       7.51 dB |       8.49 dB
------------------------------------------------------------

Instrument: DRUMS
Metrics    | Mdn (Mediana)   | M (Mean)     | SD (Std Dev.)
------------------------------------------------------------
SDR        |        6.29 dB |       5.32 dB |       7.03 dB
SIR        |       10.73 dB |       9.92 dB |       7.54 dB
SAR        |        9.01 dB |       8.73 dB |       5.30 dB
------------------------------------------------------------

Instrument: BASS
Metrics    | Mdn (Mediana)   | M (Mean)     | SD (Std Dev.)
------------------------------------------------------------
SDR        |        4.

# **AUDIBLE EXAMPLES**

In [ ]:
import IPython.display as ipd
import numpy as np
import librosa

db_test = musdb.DB(root="/content/drive/MyDrive/MUSDB18/musdb18", subsets="test", download=False)

model_test = MultiOutputUNet().to(device)
model_test.load_state_dict(torch.load("/content/drive/MyDrive/MUSDB18/MultiOutputUNet_weights_final_augment.pth", map_location=torch.device('cpu'), weights_only=True))
#model_test.load_state_dict(torch.load("/content/drive/MyDrive/MUSDB18/MultiOutputUNet_weights_final_augment.pth", weights_only=True))

# Select the first track from the test set
example_track = db_test.tracks[1]
print(f"Selected track for qualitative listening: {example_track.name}")

# Run separation
print("Separating sources... please wait...")
separated_audio = separate_track(example_track, model_test)

# Prepare original reference mix
mix_mono_original = np.mean(example_track.audio.T, axis=0)
mix_resampled_original = librosa.resample(mix_mono_original, orig_sr=example_track.rate, target_sr=TARGET_SR)

# Generate Audio Players
print("\n" + "="*50)
print("INTERACTIVE AUDIO PLAYERS")
print("="*50)

print("\n[ORIGINAL MIX] (Downsampled to 10.88 kHz)")
ipd.display(ipd.Audio(mix_resampled_original, rate=TARGET_SR))
print("-" * 50)

for t in TARGETS:
    print(f"\n[ISOLATED SOURCE] -> {t.upper()}")
    ipd.display(ipd.Audio(separated_audio[t], rate=TARGET_SR))
    print("-" * 50)

Selected track for qualitative listening: Al James - Schoolboy Facination
Separating sources... please wait...

INTERACTIVE AUDIO PLAYERS

[ORIGINAL MIX] (Downsampled to 10.88 kHz)


--------------------------------------------------

[ISOLATED SOURCE] -> VOCALS


--------------------------------------------------

[ISOLATED SOURCE] -> DRUMS


--------------------------------------------------

[ISOLATED SOURCE] -> BASS


--------------------------------------------------

[ISOLATED SOURCE] -> OTHER


--------------------------------------------------


# **Script only to download files.**

In [ ]:
import os
import zipfile
import re
import soundfile as sf
from google.colab import files

# Clean up the track name to avoid special characters invalid in filenames
track_name_clean = re.sub(r'[^\|\}\\\|\}\\\|\}\w\-_\. ]', '_', example_track.name).replace(" ", "_")
zip_filename = f"{track_name_clean}_audio_ppt.zip"

print(f" Creating the compressed archive for: {example_track.name}...")

# Create the local ZIP file
with zipfile.ZipFile(zip_filename, 'w') as zipf:

    # Export and add the resampled Original Mix
    mix_filename = f"01_{track_name_clean}_MIX_ORIGINAL.wav"
    sf.write(mix_filename, mix_resampled_original, TARGET_SR)
    zipf.write(mix_filename)
    os.remove(mix_filename)  # Remove the local temporary file to avoid cluttering Colab
    print(f"   -> Added: {mix_filename}")

    # Export and add the 4 stems isolated by the U-Net
    for i, t in enumerate(TARGETS, start=2):
        stem_filename = f"0{i}_{track_name_clean}_{t.upper()}.wav"
        sf.write(stem_filename, separated_audio[t], TARGET_SR)
        zipf.write(stem_filename)
        os.remove(stem_filename)  # Remove the temporary file
        print(f"   -> Added: {stem_filename}")

print(f"\n Downloading the archive: {zip_filename} ...")
files.download(zip_filename)
print("\n[COMPLETED] ")

 Creating the compressed archive for: Al James - Schoolboy Facination...
   -> Added: 01_Al_James_-_Schoolboy_Facination_MIX_ORIGINAL.wav
   -> Added: 02_Al_James_-_Schoolboy_Facination_VOCALS.wav
   -> Added: 03_Al_James_-_Schoolboy_Facination_DRUMS.wav
   -> Added: 04_Al_James_-_Schoolboy_Facination_BASS.wav
   -> Added: 05_Al_James_-_Schoolboy_Facination_OTHER.wav



<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>


[COMPLETED] 
